# VoxCPM2 Voice Cloning — Kaggle Notebook

This notebook uses the Kaggle GPU runtime and the reference recording already available in the dataset.

**Expected runtime:** Python 3.13 + CUDA/Tesla T4, as verified in the working session.  
**Model:** `openbmb/VoxCPM2`  
**Reference audio:** `/kaggle/input/datasets/mrsandipmandal/clonesample/sample.wav`

Run cells from top to bottom. If the notebook session resets, rerun the setup and validation cells.


## 1. Install VoxCPM2

This installation command worked in the current Kaggle environment. It uses the active kernel's Python so the package installs into the environment the notebook actually runs.

In [1]:
import sys
import subprocess

print("Python executable:", sys.executable)
result = subprocess.run(
    [sys.executable, "-m", "pip", "install", "--no-cache-dir", "voxcpm==2.0.3", "soundfile"],
    stdout=subprocess.PIPE,
    stderr=subprocess.STDOUT,
    text=True
)
print(result.stdout[-15000:])
print("Install exit code:", result.returncode)
if result.returncode != 0:
    raise RuntimeError("VoxCPM installation failed; inspect the output above.")


Python executable: /usr/bin/python3
cusparse,nvjitlink,nvrtc,nvtx]==12.8.1; platform_system == "Linux"->torch>=2.5.0->voxcpm==2.0.3) (12.5.8.93)
  Installing build dependencies: started
  Installing build dependencies: finished with status 'done'
  Getting requirements to build wheel: started
  Getting requirements to build wheel: finished with status 'done'
  Preparing metadata (pyproject.toml): started
  Preparing metadata (pyproject.toml): finished with status 'done'
  Installing build dependencies: started
  Installing build dependencies: finished with status 'done'
  Getting requirements to build wheel: started
  Getting requirements to build wheel: finished with status 'done'
  Preparing metadata (pyproject.toml): started
  Preparing metadata (pyproject.toml): finished with status 'done'
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 6.9/6.9 MB 33.5 MB/s  0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 6.1/6.1 MB 78.6 MB/s  0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 1.0

## 2. Restart the session if needed

If this is a fresh install, restart the Kaggle session after Cell 1, then continue from Cell 3. If `voxcpm` already imports successfully in the current kernel, continue directly.

In [3]:
import sys
import importlib.util
import torch

print("Python:", sys.version)
print("VoxCPM module spec:", importlib.util.find_spec("voxcpm"))
print("PyTorch:", torch.__version__)
print("CUDA available:", torch.cuda.is_available())
if torch.cuda.is_available():
    print("GPU:", torch.cuda.get_device_name(0))
else:
    print("WARNING: CUDA is not available; model inference may be slow or fail.")


Python: 3.13.15 (main, Aug  6 2026, 11:06:22) [GCC 13.3.0]
VoxCPM module spec: ModuleSpec(name='voxcpm', loader=<_frozen_importlib_external.SourceFileLoader object at 0x7d2f679c78f0>, origin='/usr/local/lib/python3.13/dist-packages/voxcpm/__init__.py', submodule_search_locations=['/usr/local/lib/python3.13/dist-packages/voxcpm'])
PyTorch: 2.11.0+cu128
CUDA available: True
GPU: Tesla T4


## 3. Verify the reference WAV

In [4]:
from pathlib import Path
import soundfile as sf
from IPython.display import Audio, display

REFERENCE_WAV = "/kaggle/input/datasets/mrsandipmandal/sample-file/sample.wav"
assert Path(REFERENCE_WAV).is_file(), f"Reference WAV not found: {REFERENCE_WAV}"

reference_audio, reference_sr = sf.read(REFERENCE_WAV)
duration = len(reference_audio) / reference_sr
print("Reference audio:", REFERENCE_WAV)
print("Sample rate:", reference_sr, "Hz")
print("Duration:", round(duration, 2), "seconds")
print("Channels:", 1 if reference_audio.ndim == 1 else reference_audio.shape[1])
print("File size:", Path(REFERENCE_WAV).stat().st_size, "bytes")
display(Audio(reference_audio, rate=reference_sr))


Reference audio: /kaggle/input/datasets/mrsandipmandal/sample-file/sample.wav
Sample rate: 24000 Hz
Duration: 19.97 seconds
Channels: 1
File size: 958598 bytes


## 4. Load VoxCPM2

The model weights are downloaded on first run, so Kaggle Internet must be enabled. This can take a while. The following API call is the one verified in the working setup.

In [5]:
import torch
from voxcpm import VoxCPM

model = VoxCPM.from_pretrained(
    "openbmb/VoxCPM2",
    load_denoiser=False,
    device="cuda" if torch.cuda.is_available() else "cpu",
)
print("VoxCPM2 model loaded successfully.")


Reconstructing (incomplete total...): |          |  0.00B /  0.00B            

Fetching 9 files:   0%|          | 0/9 [00:00<?, ?it/s]

voxcpm_model_path: /root/.cache/huggingface/hub/models--openbmb--VoxCPM2/snapshots/32279effe8c19989596f05d353d1447f51d9e915, zipenhancer_model_path: None, enable_denoiser: False
/usr/local/lib/python3.13/dist-packages/torch/nn/utils/weight_norm.py:144: FutureWarning: `torch.nn.utils.weight_norm` is deprecated in favor of `torch.nn.utils.parametrizations.weight_norm`.
  WeightNorm.apply(module, name, dim)
Loading AudioVAE from pytorch: /root/.cache/huggingface/hub/models--openbmb--VoxCPM2/snapshots/32279effe8c19989596f05d353d1447f51d9e915/audiovae.pth
Running on device: cuda, dtype: bfloat16
Loading model from safetensors: /root/.cache/huggingface/hub/models--openbmb--VoxCPM2/snapshots/32279effe8c19989596f05d353d1447f51d9e915/model.safetensors
Loaded VoxCPM2Model
Warm up VoxCPMModel...
  0%|          | 0/10 [00:00<?, ?it/s]W1028 19:20:33.943000 49 torch/_inductor/utils.py:1731] [0/0] Not enough SMs to use max_autotune_gemm mode
/usr/local/lib/python3.13/dist-packages/torch/_inductor/com

VoxCPM2 model loaded successfully.


## 5. Generate cloned speech

Edit `TEXT_TO_SPEAK` to the text you want spoken in the reference voice. The output is saved under `/kaggle/working/`.

In [8]:
TEXT_TO_SPEAK = """
(Speak at a moderately fast pace, clear and confident news-anchor delivery,
brisk rhythm, natural pauses, articulate technical terms.)

Critical cybersecurity alerts: Last week and today.

Cybersecurity threats continue to target developer infrastructure,
AI supply chains, e-commerce platforms, and enterprise applications.

Last week, October twenty-first to twenty-seventh, twenty twenty-six.

GitLab remote code execution: CVE twenty twenty-six, one ten two six four.
A reported critical vulnerability may put vulnerable self-managed
GitLab instances at risk.

LiteLLM supply-chain compromise.
Malicious package releases and affected container images may expose
AI API keys and cloud credentials.

Today, October twenty-eighth, twenty twenty-six.

Google Brotli and Node2Shell.
Reported exploitation attempts may involve memory corruption
and potential remote code execution.

Adobe Commerce and Magento.
Reported attacks target vulnerable e-commerce installations
through malicious file uploads.

Oracle E-Business Suite.
Reported probing targets a critical SQL injection vulnerability.

Security checklist for developers and IT teams:
Apply verified security patches.
Audit dependencies and container images.
Rotate potentially exposed credentials.
Monitor server logs and investigate suspicious activity.
Secure internet-facing applications and administrative interfaces.

Stay proactive. Verify every alert. Patch before attackers exploit it.
Follow trusted sources such as CERT-In, CISA, and official vendor advisories.
"""

audio_out = model.generate(
    text=TEXT_TO_SPEAK,
    reference_wav_path=REFERENCE_WAV,
    cfg_value=2.0,
    inference_timesteps=8,
)

import soundfile as sf
import numpy as np

if hasattr(audio_out, "detach"):
    audio_out = audio_out.detach().float().cpu().numpy()

audio_out = np.asarray(audio_out).squeeze()
sample_rate = model.tts_model.sample_rate

sf.write("/kaggle/working/cybersecurity_alerts.wav",
         audio_out, sample_rate)

print("Duration:", round(len(audio_out) / sample_rate, 2), "seconds")
display(Audio(audio_out, rate=sample_rate))

 35%|███▌      | 624/1774 [03:14<05:58,  3.21it/s]


Duration: 100.0 seconds


## 6. Download the generated WAV

In Kaggle, the output also appears in the notebook's `/kaggle/working` files panel.

In [ ]:
from IPython.display import FileLink, display
display(FileLink("/kaggle/working/cloned_speech.wav"))


## Troubleshooting

- **`ModuleNotFoundError: voxcpm`**: rerun Cell 1 with the same kernel, restart the session, then rerun Cell 2 and subsequent cells.
- **Model download error**: enable Internet in Kaggle notebook settings and rerun Cell 4.
- **CUDA out-of-memory**: restart the session, ensure no other GPU process is active, and retry. This notebook disables the denoiser to reduce memory use.
- **Generation API error**: capture the complete traceback; package APIs may differ by release.
- **Dependency resolver warnings**: some unrelated preinstalled Kaggle packages may have conflicting dependency pins. If VoxCPM imports and inference works, avoid upgrading unrelated packages blindly.
